In [1]:
import pandas as pd
import numpy as np
import plotly.express as px
import plotly.graph_objects as go

### define data configuration

In [2]:
date_start = pd.to_datetime('2019-01-01')
date_end = pd.to_datetime('2019-01-08')

count_datapoints_per_minute = 1
count_of_predictor_variables = 4

noise_lvl_predictor = [0.1, 0.2, 0.3, 0.1]
multiplier_predictor = [1, 2, 3, 4]

noise_lvl_target = 0.05
multiplier_target = 7

name_predictor_var_prefix = "var"
name_target_var = "target"

np.random.seed(1)

### initialize empty dataframe

In [3]:
df = pd.DataFrame()

### create random timestamps

In [4]:
start_u = date_start.value//10**9
end_u = date_end.value//10**9

In [5]:
start_u

1546300800

In [6]:
end_u

1546905600

In [7]:
total_number_datapoints = int(abs((date_start - date_end)/pd.Timedelta("1day"))*24*60*count_datapoints_per_minute)
total_number_datapoints

10080

In [8]:
timestamp = pd.to_datetime(np.random.randint(start_u, end_u, total_number_datapoints), unit='s')
timestamp = timestamp.sort_values()
timestamp.name='timestamp'
timestamp

DatetimeIndex(['2019-01-01 00:02:42', '2019-01-01 00:02:59',
               '2019-01-01 00:04:03', '2019-01-01 00:04:24',
               '2019-01-01 00:05:47', '2019-01-01 00:06:20',
               '2019-01-01 00:06:54', '2019-01-01 00:07:44',
               '2019-01-01 00:07:47', '2019-01-01 00:07:55',
               ...
               '2019-01-07 23:48:12', '2019-01-07 23:49:23',
               '2019-01-07 23:49:45', '2019-01-07 23:50:07',
               '2019-01-07 23:51:07', '2019-01-07 23:51:52',
               '2019-01-07 23:53:18', '2019-01-07 23:53:19',
               '2019-01-07 23:53:56', '2019-01-07 23:55:56'],
              dtype='datetime64[ns]', name='timestamp', length=10080, freq=None)

In [9]:
df.index = timestamp

### create random predictors and target

In [10]:
number_of_cycles = (date_end - date_start).days
length = np.pi * 2 * number_of_cycles

# predictors
for number in range(count_of_predictor_variables):
    
    var_name = name_predictor_var_prefix + str(number)
    
    wave = np.sin(np.arange(0, length, length / total_number_datapoints) - np.random.random(size=1)[0]*np.pi)*multiplier_predictor[number-1] + multiplier_predictor[number-1]*1.2
    wave = wave + np.random.normal(0,noise_lvl_predictor[number-1],len(wave))
    df[var_name] = wave
    
# target
wave = np.sin(np.arange(0, length, length / total_number_datapoints) - np.random.random(size=1)[0]*np.pi)*multiplier_target + multiplier_target*1.2
wave = wave + np.random.normal(0,noise_lvl_target,len(wave))
df[name_target_var] = wave
        
df

,var0,var1,var2,var3,target
timestamp,,,,,
2019-01-01 00:02:42,1.886022,0.126352,0.799021,2.912543,2.658716
2019-01-01 00:02:59,2.044087,0.360150,0.856998,3.060680,2.739077
2019-01-01 00:04:03,1.939325,0.022628,0.639995,2.798097,2.745476
2019-01-01 00:04:24,2.243638,0.227285,0.770294,3.278902,2.710543
2019-01-01 00:05:47,2.368477,0.262497,0.556242,2.731213,2.788331
...,...,...,...,...,...
2019-01-07 23:51:52,1.934420,0.025396,0.603276,2.543722,2.627305
2019-01-07 23:53:18,2.084561,0.316460,0.454799,2.938782,2.617830
2019-01-07 23:53:19,2.143033,0.105172,0.675919,2.551417,2.644591


### plot data

In [11]:
fig = go.Figure()

for col in df.columns:
    
    fig.add_trace(go.Scatter(
        mode="lines",
        x=df.index.values,
        y=df[col].values,
        name=col
    ))
    
fig.show()

### save dataframe to csv

In [12]:
df.to_csv("./data_edge_consideration.csv")